# Introducción a la Visualización de Datos en Humanidades con Altair
---
Visualización de Datos del Máster Universitario en Humanidades Digitales (2022/2023)

M. Rincón Zamorano y A. Benito-Santos.

## 👋👋 ¡Bienvenid@!

En este cuaderno, vamos a presentar la biblioteca **declarativa** de visualización para Python [Altair](https://altair-viz.github.io/), con un enfoque centrado en visualizar textos y datos obtenidos de ellos.

Para ilustrar el uso de esta herramienta, se plantea la construcción de un panel interactivo basado en la técnica de interacción "brushing and linking." Aunque lo veremos más adelante en profundidad, te puedo adelantar que la correcta implementación de esta técnica implica conectar en un panel de mandos (dashboard) de manera coherente dos vistas que han sido diseñadas por separado.


### Algunas consideraciones
Con *declarativo*, queremos decir que para generar los gráficos, el usuario da una espeficicación de alto nivel de lo que queremos que incluya en términos de *datos*, *símbolos*, y *canales/codificaciones*. Esto contrasta con otros enfoques en los que implementaremos la visualización con bucles for, llamadas a un API gráfica de bajo nivel, etc. como haríamos en otras bibliotecas como [D3](https://d3js.org/) o [matplotlib](https://matplotlib.org/).


La idea fundamental es que declararemos relaciones entre campos en nuestros datos y canales visuales (como por ejemplo, la *posición en el eje de abscisas o en el eje de ordenadas*, *color*, *transparencia*, etc...), dejando que el resto de los detalles del gráfico se manejen automáticamente. Partiendo de esta idea de crear gráficos de manera declarativa, se pueden crear muchas visualizaciones, desde las más simples hasta algunas más complejas, usando una gramática concisa.


### Nota
Este cuaderno interactivo puede ser ejecutado en Google Colab. ¿No conoces Google Colab? Echa un vistazo a [estos recursos en línea](https://colab.research.google.com/?hl=es). Además, si te fijas, no puedes editarlo aún (aunque sí hacerlo funcionar). Para poder hacerlo, tienes que hacer una copia en tu carpeta personal de Google Drive: desde el menú superior, haz: **Archivo → Guardar una copia en Drive**.

Si prefieres usar el cuaderno en tu máquina, simplemente descarga este fichero a tu disco duro y lánzalo usando tu instalación de Jupyter Notebook/Lab.

Cuando lo hayas hecho, podrás editar los ejemplos de código y añadir tus propias notas.

¿Todo listo? Bien, pues...¡Comencemos!

## Altair

Altair nos va a permitir interactuar desde Python con una gramática de visualización muy poderosa y concisa, llamada Vega-Lite, con la que podremos crear un montón de visualizaciones interactivas diferentes con mínimo esfuerzo.

[Vega-Lite](https://vega.github.io/vega-lite/) es una gramática de alto nivel para crear gráficos interactivos. Altair ofrece una [API](https://es.wikipedia.org/wiki/Interfaz_de_programaci%C3%B3n_de_aplicaciones) en Python que genera especificaciones Vega-Lite en formato JSON, lo cual lo hace perfecto para hacerlo funcionar en entornos de cuadernos de computación como Jupyter o Google Colab, ya que esta especificación se renderiza directamente al navegador por medio de Javascript.

Más sobre cómo se implementó la gramática de los gráficos en el vídeo de presentación de [Vega-Lite en OpenVisConf 2017](https://www.youtube.com/watch?v=9uaHRWj04D4)

## Preparando el entorno
Para poder hacer funcionar los ejemplos de este cuaderno, es necesario importar primero algunas **dependencias y datos**.

### Datos

En este cuaderno vamos a tomar como base para la exploración un corpus (conjunto de datos textual) de poemas del poeta y dramaturgo español [Federico García Lorca](https://es.wikipedia.org/wiki/Federico_Garc%C3%ADa_Lorca) (1898-1936).

Empezando por los datos, vamos a descargar al entorno de ejecución de este cuaderno las obras poéticas de Federico García Lorca  (obtenidas de https://federicogarcialorca.net/).

Una vez descargado, puedes ver el fichero `poems.json` haciendo *click* en el icono de la carpeta situado en la barra lateral izquierda.

Más adelante, utilizaremos un algoritmo para procesar el texto de los poemas y producir una [escansión](https://dle.rae.es/escansi%C3%B3n) de los versos de los mismos de manera automática.

In [ ]:
!wget https://raw.githubusercontent.com/ale0xb/visualizing-garcialorca/main/poems/poems.json -O poems.json
!wget https://raw.githubusercontent.com/ale0xb/visualizing-garcialorca/main/poems/scansions.json -O scansions.json

--2024-02-08 16:18:22--  https://raw.githubusercontent.com/ale0xb/visualizing-garcialorca/main/poems/poems.json
Resolving raw.githubusercontent.com (raw.githubusercontent.com)... 185.199.108.133, 185.199.109.133, 185.199.110.133, ...
Connecting to raw.githubusercontent.com (raw.githubusercontent.com)|185.199.108.133|:443... connected.
HTTP request sent, awaiting response... 200 OK
Length: 389431 (380K) [text/plain]
Saving to: ‘poems.json’

poems.json          100%[===================>] 380.30K  --.-KB/s    in 0.03s   

2024-02-08 16:18:23 (10.8 MB/s) - ‘poems.json’ saved [389431/389431]

--2024-02-08 16:18:23--  https://raw.githubusercontent.com/ale0xb/visualizing-garcialorca/main/poems/scansions.json
Resolving raw.githubusercontent.com (raw.githubusercontent.com)... 185.199.111.133, 185.199.110.133, 185.199.109.133, ...
Connecting to raw.githubusercontent.com (raw.githubusercontent.com)|185.199.111.133|:443... connected.
HTTP request sent, awaiting response... 200 OK
Length: 13436973 

### Dependencias
Una parte de los ejemplos que veremos está centrada en el análisis visual de los patrones rítmicos de los poemas que acabamos de descargar.

Para obtener dichas métricas, se empleó la biblioteca de escansión [rantanplan](https://github.com/linhd-postdata/rantanplan), creada recientemente por investigadores del [LiNHD](https://linhd.uned.es/) de la UNED. (Ver paper [aquí](http://arxiv.org/abs/2011.09567)). Rantanplan va a producir la escansión el tipo de estrofa del texto que le pasemos (por ej., cuarteto, lira, soneto...).

Y continuamos ahora con el resto de dependencias:

### Importando
Finalmente, importamos las dependencias que hemos instalado en el paso anterior.

In [ ]:
import pandas as pd
import altair as alt
import spacy
import nltk
import numpy as np
import itertools
import json

alt.data_transformers.enable('default', max_rows=None)

DataTransformerRegistry.enable('default')

## La Gramática de los Gráficos
### Datos
Lo primero, cargaremos los poemas en un data frame de [Pandas](https://pandas.pydata.org/), que es el formato de datos que emplea Altair (en forma de tabla).

In [ ]:
poems_df = pd.read_json("poems.json")
poems_df['index'] = poems_df.index

El data frame es una estructura de datos que contiene columnas con nombre llamados *campos*. Estos campos son claves en el proceso de creación de visualizaciones con Altair.


Y ahora vemos la pinta que tienen nuestros datos: nuestro data frame contiene un poema por fila y 6 columnas.

In [ ]:
poems_df.head()

,book,body,subtitle,title,n_verses,verse_lengths,index
0,Canciones,Cantan las siete\ndoncellas.\n\n(Sobre el ciel...,Canción de las siete doncellas (Teoría del arc...,Teorías,14,"[5, 3, 6, 6, 7, 6, 6, 6, 5, 3, 7, 7, 6, 6]",0
1,Canciones,"Hinojo, serpiente y junco.\nAroma, rastro y pe...",Nocturno esquemático.,Teorías,4,"[8, 8, 8, 8]",1
2,Canciones,Sábado.\nPuerta de jardín.\n\nDomingo.\nDía gr...,Canción del colegial.,Teorías,17,"[2, 6, 3, 3, 2, 2, 5, 2, 3, 5, 2, 2, 3, 5, 3, ...",2
3,Canciones,El canto quiere ser luz.\nEn lo oscuro el cant...,El canto quiere ser luz,Teorías,7,"[8, 8, 8, 8, 8, 8, 3]",3
4,Canciones,Los días de fiesta\nvan sobre ruedas.\nEl tío-...,Tío vivo.,Teorías,30,"[5, 5, 7, 4, 5, 6, 6, 8, 7, 7, 6, 7, 8, 7, 5, ...",4


Por ejemplo, el campo "*book*" contiene el libro al que pertenece el poema.
Una pregunta que puede surgirnos es cuántos libros distintos hay en nuestros datos. Lo podemos saber así:

In [ ]:
poems_df['book'].unique()

array(['Canciones', 'Libro de Poemas',
       'Llanto por Ignacio Sánchez Mejías', 'Poema del Cante Jondo',
       'Poemas Sueltos', 'Poeta en Nueva York', 'Romancero Gitano',
       'Sonetos del Amor Oscuro'], dtype=object)

Siguiendo está lógica, otra pregunta que nos puede surgir es cuántos poemas hay incluidos en cada libro:

In [ ]:
poems_df['book'].value_counts()

Canciones                            112
Poemas Sueltos                        90
Libro de Poemas                       69
Poema del Cante Jondo                 51
Poeta en Nueva York                   35
Romancero Gitano                      23
Sonetos del Amor Oscuro                9
Llanto por Ignacio Sánchez Mejías      4
Name: book, dtype: int64

Con esta información, es evidente que podríamos crear nuestra primera visualización, un histograma. Vamos a ver cómo Altair nos permite hacerlo siguiendo un enfoque inspirado en la "Gramática de los Gráficos" de Wilkinson.

### El Objeto Chart
El objeto fundamental en Altair es `Chart`, que toma como argumento un data frame. Vamos a definir un dataframe con las cuentas de poemas de cada libro:

In [ ]:
poems_count_df = poems_df['book'].value_counts().to_frame().reset_index().rename(
    columns={"book": "count", "index": "book"} #renombro las columnas
)

In [ ]:
poems_count_df

,book,count
0,Canciones,112
1,Poemas Sueltos,90
2,Libro de Poemas,69
3,Poema del Cante Jondo,51
4,Poeta en Nueva York,35
5,Romancero Gitano,23
6,Sonetos del Amor Oscuro,9
7,Llanto por Ignacio Sánchez Mejías,4


In [ ]:
chart = alt.Chart(poems_count_df)

Date cuenta de que hasta ahora, sólo hemos definido el objeto `Chart` y le hemos pasado nuestro data frame con poemas. Pero todavía no le hemos dicho que haga *nada* con dichos datos.

### Marcas y codificaciones
Una vez que tenemos inicializado nuestro objeto `Chart`, es momento de especificar cómo queremos que sean visualizados nuestros datos. Para ello, lo primero que haremos será indicar el tipo de marca gráfica (o figura geométrica) queremos usar para representar los datos. Podemos especificar el atributo `mark` del objeto `chart` usando sus métodos que comiencen por mark (`Chart.mark_*`).

Por ejemplo, podríamos mostrar los datos usando el punto con `Chart.mark_point()`:

In [ ]:
chart.mark_point()

alt.Chart(...)

Lo que ha ocurrido es que Altair ha pintado un punto por cada fila (libro) de nuestro data frame. Como no le hemos especificado qué posición han de tomar, los puntos simplemente se pintan uno encima de otro, ya que por defecto, a todos se les da la misma coordenada (0,0).

Para hacer que los puntos se separen, tenemos que asociar (codificar) campos de nuestro conjunto de datos a canales visuales. Por ejemplo, podemos codificar el campo "book" a una posición en el eje y.


In [ ]:
chart.mark_point().encode(
    x='book',
)

alt.Chart(...)

Como ves, lo que ha hecho el método `encode` es asociar una columna al canal visual de la posición del punto en el eje de ordenadas (aunque podría haberlo hecho a otro, como `color`, `x`, `shape`, `size`, etc...).

Además, Altair es suficientemente inteligente como para determinar el tipo de dato de la columna en cuestión, que en este caso es de tipo _nominal_, es decir, que contiene valores desordenados y categóricos. A su vez, esto permite que Altair, por defecto, elija el tipo de representación más adecuada para nuestros datos.

Aunque hemos sido capaces de separar los puntos usando el valor de una columna, todavía estamos omitiendo información importante en la visualización: no nos dice cuántos poemas contiene cada libro. Vamos a solucionar esto codificando el campo `count` a otro canal, el tamaño del círculo (`size`).

In [ ]:
chart.mark_point().encode(
    x='book',
    size='count'
)

alt.Chart(...)

Esto pinta mejor. Ahora podemos ver que los libros de nuestro corpus que contienen más poemas son "Canciones" y "Poemas Sueltos". Pero, ateniéndote a lo que ves en la visualización, ¿sabrías decir con total seguridad cuál de los dos es el mayor?

Esta respuesta es difícil de contestar porque el tamaño del círculo es un canal visual en el que es complicado establecer comparaciones "finas". Para esta tarea, es mucho mejor usar la posición (Ver "*The Semiology of Graphics*" del cartógrafo francés J. Bertin).

Vamos a transformar nuestra visualización en un diagrama de barras. ¿Cómo? Cambiando el tipo de marca visual que le pasamos al objeto `Chart`.

In [ ]:
chart.mark_bar().encode(
    x=alt.X('book'),
    y='count'
)

alt.Chart(...)

Como ves, ahora hemos empleado `mark_bar()` para emplear barras en vez de puntos. También hemos asociado la coordenada `y` (el alto de la barra), al número de poemas contenidos en la colección, consiguiendo el histograma que buscábamos.

Aunque el gráfico que hemos obtenido es perfectamente funcional, ya que consigue lo que se buscaba, podemos todavía mejorarlo algo. **¿Se te ocurre cómo?**

### Mejorando el histograma
El gráfico presenta dos problemas fundamentales:
1. Las etiquetas del eje X son difíciles de leer porque aparecen giradas 90 grados en sentido antihorario.
2. Es difícil establecer un orden de los libros en base al número de poemas que contiene cada uno. Podemos facilitar esta tarea cambiando el orden de los elementos en el eje X de acuerdo al valor `count`.

In [ ]:
chart.mark_bar().encode(
    x=alt.X('book',
            sort='-y',
            axis=alt.Axis(labelAngle=-45)),
    y=alt.Y('count')
)

alt.Chart(...)

Fíjate que hemos usado dos métodos especiales para definir las codificaciones a `x` e `y`, `alt.X()` y `alt.Y()`. Esta alternativa es útil para pasar más parámetros a la codificación, como ha sido el caso. Veremos algún ejemplo de esto más adelante.

### Transformaciones: Agregación.
Si te das cuenta, en el ejemplo del histograma hemos tenido que agregar los datos en Pandas creando un dataframe nuevo (`poems_count_df()`) antes de pasárselos a Altair .

Sin embargo, Altair también permite hacer esto internamente `poems_df()`. Por suerte, Altair permite hacer esto a través de una variedad de funciones de agregación: min (mínimo), max (máximo), average (media), median (mediana), y stdev (desviación estándar), que podemos incluir en la descripción de nuestras codificaciones. Por lo tanto, una manera de conseguir lo mismo sin usar un data frame intermedio es:


In [ ]:
chart.mark_bar().encode(
    x=alt.X('book:N',
            sort='-y',
            axis=alt.Axis(labelAngle=-45)),
    y='count'
)

alt.Chart(...)

## Visualizando poemas: Combinando vistas

Una vez que visto lo básico, vamos a movernos a algunos ejemplos en los que visualizaremos el ritmo de los los poemas usando datos obtenidos con la biblioteca `rantanplan`.

Los resultados del análisis del ritmo, los almacenaremos en nuevo data frame llamado `verses_df` que albergará todas las sílabas de todos los versos de los poemas incluidos en nuestra colección.

In [ ]:
with open('scansions.json', 'r') as fr:
    scansions = json.load(fr)

Rantanplan genera un objeto con toda la información obtenida a partir del texto del poema en 7 claves (más info [aquí](https://rantanplan.readthedocs.io/en/latest/readme.html#documentation)])

*   **tokens**: Información sobre la silibificación de las palabras.
*   **phonological_groups**: Agrupaciones de sílabas en base a principios fonológicos (por ej. cuando se juntan sílabas de palabras distintas en la [sinalefa](https://dle.rae.es/sinalefa)).
*   **rhythm**: Información del ritmo del verso, representado como una secuencia de símbolos "+" (con énfasis) y "-" (sin énfasis).
*   **structure**: Tipo de estrofa que se estima que tiene el verso.
*   **rhyme**: Tipo de rima que tiene el verso dentro de la estrofa. (Ej: Para un patrón de rima "abab", en el que el primer verso rima con el tercero y el segundo con el cuarto, "a" o "b".
*   **ending**: Terminación del verso a tener en cuenta para calcular la información de rima.
*   **ending_stress**: Índice de la vocal que lleva el último acento (-1: última sílaba, -2: penúltima sílaba, etc.).
*   **rhyme_type**: Tipo rima, indica si es asonante o consonante.
*   **rhyme_relaxation**: Si se aplican reglas de relajación de la rima.


Debajo se muestra el texto de un poema escogido al azar y la salida de rantanplan para su primer verso:

In [ ]:
print(poems_df.iloc[205]['body'])

¡Ay, petenera gitana!
¡Yayay petenera!
Tu entierro no tuvo niñas
buenas.
Niñas que le dan a Cristo muerto
sus guedejas,
y llevan blancas mantillas
en las ferias.
Tu entierro fue de gente
siniestra.
Gente con el corazón
en la cabeza,
que te siguió llorando
por las callejas.
¡Ay, petenera gitana!
¡Yayay petenera!


In [ ]:
scansions[205][0].keys()

dict_keys(['tokens', 'phonological_groups', 'rhythm'])

In [ ]:
scansions[205][0]

{'tokens': [{'symbol': '¡'},
  {'word': [{'syllable': 'Ay', 'is_stressed': False, 'is_word_end': True}],
   'stress_position': 0},
  {'symbol': ','},
  {'word': [{'syllable': 'pe', 'is_stressed': False},
    {'syllable': 'te', 'is_stressed': False},
    {'syllable': 'ne', 'is_stressed': True},
    {'syllable': 'ra', 'is_stressed': False, 'is_word_end': True}],
   'stress_position': -2},
  {'word': [{'syllable': 'gi', 'is_stressed': False},
    {'syllable': 'ta', 'is_stressed': True},
    {'syllable': 'na', 'is_stressed': False, 'is_word_end': True}],
   'stress_position': -2},
  {'symbol': '!'}],
 'phonological_groups': [{'syllable': 'Ay',
   'is_stressed': False,
   'is_word_end': True},
  {'syllable': 'pe', 'is_stressed': False},
  {'syllable': 'te', 'is_stressed': False},
  {'syllable': 'ne', 'is_stressed': True},
  {'syllable': 'ra', 'is_stressed': False, 'is_word_end': True},
  {'syllable': 'gi', 'is_stressed': False},
  {'syllable': 'ta', 'is_stressed': True},
  {'syllable': 'na'

In [ ]:
lengths = [[item['rhythm']['length'] for item in scansion] for scansion in scansions] # Obtenemos la longitud (en sílabas) de cada verso
poems_df['verse_lengths'] = lengths # Y la almacenamos en una columna de poems_df
poems_df['n_verses'] = [len(l) for l in lengths] # También calculamos el número de versos de cada poema y lo almacenamos también en poems_df

In [ ]:
# En este dataframe vamos a guardar todos las sílabas de todos los versos de
# todos los poemas de nuestra colección, junto con la información de la acentuación.

verses = []
for h, scansion in enumerate(scansions):
  for i, line in enumerate(scansion):
    for j, phono_group in enumerate(line['phonological_groups']):
        verses.append({
            'poem': h, # Índice del poema al que pertenece el verso
            'x': j, # posición de la sílaba en el verso
            'y': i, # posición del verso en el poema
            'syllable': phono_group['syllable'], #Texto de la sílaba
            'is_stressed': int(phono_group['is_stressed']), # Indica si la sílaba va acentuada
            'book': poems_df.iloc[h]['book'], # Colección a la que pertenece dentro del corpus
            'n_verses': poems_df.iloc[h]['n_verses'], # Número de versos del poema
            'verse_length': poems_df.iloc[h]['verse_lengths'][i] # Longitud del verso
        })

verses_df = pd.DataFrame(verses)

Una vez creado, nuestro data frame tiene la siguiente pinta:

In [ ]:
verses_df.head()

,poem,x,y,syllable,is_stressed,book,n_verses,verse_length
0,0,0,0,Can,1,Canciones,14,5
1,0,1,0,tan,0,Canciones,14,5
2,0,2,0,las,0,Canciones,14,5
3,0,3,0,sie,1,Canciones,14,5
4,0,4,0,te,0,Canciones,14,5


Como se puede ver, para cada sílaba (fila) tenemos los siguientes campos o columnas:

*   **poem**: El poema al que pertenece.
*   **x**: posición de la sílaba en el verso.
*   **y**: verso al que pertece la sílaba en cuestión.
*   **syllable**: el texto de la sílaba.
*   **is_stressed**: si la sílaba va acentuada.
*   **book**: libro al que pertenece.
*   **n_verses**: número de versos que tiene el poema al que pertenece la sílaba.
*   **verse_length**: longitud total del verso al que pertenece la sílaba.

Para construir nuestra visualización final, vamos a combinar dos visualizaciones siguiendo un enfoque típico de la lectura aumentada (combinando en un sólo gráfico el texto del poema y los acentos extraídos por el algoritmo).

Empezaremos por la primera:

In [ ]:
poem = verses_df[verses_df['poem'] == 205] #Elegimos un poema

In [ ]:
poem

,poem,x,y,syllable,is_stressed,book,n_verses,verse_length
39880,205,0,0,Ay,0,Poema del Cante Jondo,16,8
39881,205,1,0,pe,0,Poema del Cante Jondo,16,8
39882,205,2,0,te,0,Poema del Cante Jondo,16,8
39883,205,3,0,ne,1,Poema del Cante Jondo,16,8
39884,205,4,0,ra,0,Poema del Cante Jondo,16,8
...,...,...,...,...,...,...,...,...
39974,205,1,15,yay,1,Poema del Cante Jondo,16,6
39975,205,2,15,pe,0,Poema del Cante Jondo,16,6
39976,205,3,15,te,0,Poema del Cante Jondo,16,6
39977,205,4,15,ne,1,Poema del Cante Jondo,16,6


In [ ]:
alt.Chart(poem).encode(
            x=alt.X('x:O',
                    title='syllable'), #codificamos el ordinal de la sílaba en la línea a la posición en el eje X
            y=alt.Y('y:O', #codificamos el número de verso de la sílaba a la posición en el eje Y.
                    title='verse number')
          ).mark_text().encode( #Empleamos ahora un nuevo símbolo, el texto.
              text='syllable:N', #Le decimos que queremos que muestre el texto de la sílaba.
          ).properties(width=300) #Para evitar que el texto se agolpe, le damos suficiente ancho a nuestro gráfico.

alt.Chart(...)

Ok, ya tenemos el texto del poema. Vamos a crear otra visualización, llamada mapa de calor, que represente dónde van los acentos en este poema.

In [ ]:
alt.Chart(
      poem
      ).encode(
          x=alt.X('x:O', #El eje X e Y funcionan igual que antes...
                  title='syllable'),
          y=alt.Y('y:O',
                  title='verse number')
#Ahora usamos un rectángulo que colorearemos en azul/naranja dependiendo de si
#la sílaba que representa va acentuada o no.
  ).mark_rect().encode(
      color='is_stressed:N'
  ).properties(width=300)

alt.Chart(...)

Ahora que tenemos las dos visualizaciones, vamos a definir una función que las combine en una sola.

Vamos a crear este nuevo gráfico reutilizando y modificando una definición base. En vez de crear dos `Chart` distintos, como hemos arriba, podemos invocar el método `mark_rect()` o `mark_text()` para crear la versión que deseemos. Finalmente, combinaremos los dos mediante el operador `+` que va a superponer en capas las dos visualizaciones.

In [ ]:
def draw_poem_stress(verses_df):
  base = alt.Chart( #Usamos un sólo objeto chart.
      verses_df
      ).encode(
          x=alt.X('x:O',
                  title='syllable'),
          y=alt.Y('y:O',
                  title='verse number')
  )

  heatmap = base.mark_rect().encode( #Derivamos el heatmap
      color='is_stressed:N'
  )

  text = base.mark_text().encode( #Y el texto
      text='syllable:N',
      color=alt.value('white')
  )

  return (heatmap + text).properties(width=300) #Usamos el operador

In [ ]:
draw_poem_stress(poem)

alt.LayerChart(...)

In [ ]:
draw_poem_stress(verses_df[verses_df['poem'] == np.random.choice(verses_df['poem'].unique())])

alt.LayerChart(...)

*Voilà*! Hemos podido combinar texto y gráficos en una única visualización en la que combinamos el texto original de los poemas con elementos obtenidos a través de un proceso algorítmico, facilitando lo que se llama una **lectura aumentada** del poema.

### Alternativas
Una pregunta que nos podría asaltar en este punto es, ¿existen diseños alternativos que cumplan la misma funcionalidad? Casi siempre, la respuesta a esta pregunta es un rotundo "sí," y elegir **cuál de todos los posibles diseños es el mejor** implica evaluar la visualización con usuarios reales (por ej. expertos en literatura) efectuando la tarea en cuestión, siguiendo los [principios del diseño centrado en el usuario](https://es.wikipedia.org/wiki/Dise%C3%B1o_centrado_en_el_usuario) (DCU).

En nuestro caso, una posible representación alternativa podría usar sólo texto y emplear distintos canales del mismo para codificar nuestros datos. Por ejemplo:

In [ ]:
def draw_poem_stress_text(verses_df):
  return alt.Chart(
          verses_df
          ).encode( #Esto es igual que antes
              x=alt.X('x:O',
                      title='syllable'),
              y=alt.Y('y:O',
                      title='verse number')
      ).mark_text().encode(
          text='syllable:N',
          #La "novedad" es que vamos a codificar el acento al tamaño de la letra...
          size=alt.Size('is_stressed:N',
                        scale=alt.Scale(domain=[0, 1],
                                        range=[8,14])),
          color='is_stressed:N' #...y al color.
      ).properties(width=300)

In [ ]:
draw_poem_stress_text(poem)

alt.Chart(...)

### Agregando de otra manera
Una de las ventajas de la visualización de datos es que podemos detectar patrones en grandes volúmenes de datos rápidamente. Imagina ahora que quisiéramos visualizar los patrones rítmicos de muchos poemas *a la vez*.

Antes vimos que podíamos usar las funciones de agregación de Altair, como `count()` para hacer agregaciones. Sin embargo, ese enfoque más simple no nos es útil ahora ya que queremos agregar por múltiples campos (antes sólo lo hacíamos por uno). Además, vamos a añadir (de manera muy sencilla) nuestra primera técnica de interacción, un tooltip, un recurso sumamente útil para permitir una exploración más efectiva de los datos.

In [ ]:
xAxis = alt.X('x:O', title="Sílaba")
yAxis = alt.Y('y:O', title='Verso')

poems_verses_df = verses_df[verses_df['poem'].isin([205, 206, 207])]

alt.Chart(poems_verses_df).transform_aggregate(
    sum_stress='sum(is_stressed)',
    groupby=['x', 'y']
).mark_rect().encode(
    x=xAxis,
    y=yAxis,
    color='sum_stress:Q',
    tooltip=['sum_stress:Q'] #Tooltip (inte)
)

alt.Chart(...)

En Altair, vamos a contar con otros muchos tipos de transformaciones (metodos `transform_*`) para agregar, filtrar, derivar nuevas columnas a partir de las viejas... Puedes ver la referencia completa [aquí](https://altair-viz.github.io/user_guide/transform/index.html).

---

### Desagregando
A veces, vamos a querer visualizar resúmenes de un conjunto grande de datos juntos. Esto significa que haremos cálculos en base a una agregación, y luego lo sacaremos por pantalla en base a otra agregación que elijamos (en contraposición a usar una única agregación).

Vamos a verlo con un ejemplo. Imagina que queremos analizar cómo está distribuída la variable `n_verses` (número de versos de un poema) por colección (columna `book`). Podríamos estar tentados de hacer lo siguiente:

In [ ]:
alt.Chart(poems_df).mark_bar().encode(
    alt.X("n_verses:Q", bin=True),
    y='count()',
    color='book'
)

alt.Chart(...)

Aunque hace lo que se espera, esta visualización no es muy efectiva. No es fácil comparar la dispersión por colecciones. Además, el número de colecciones es difícil de apreciar, y mucho más comparar segmentos del mismo o distinto color en diferentes intervalos.

Para arreglar este problema, es importante darse cuenta de lo que está haciendo Altair automáticamente por nosotros: los datos están agregados en 2 dimensiones (el intervalo de `n_verses` y `book`). Esto es así porque al codificar `book` al color de la barra, Altair entiende que tiene que agregar los datos así, para crear segmentos en cada barra.

Sin embargo, podemos codificar `book` a posición con un tipo de gráfico que seguramente hayas visto por ahí: el gráfico facetado.

En Altair es muy fácil crear este tipo de gráficos. Tan sólo tenemos que añadir una llamada al método correspondiente `facet()` e indicarle la variable que queremos que emplee.

In [ ]:
alt.Chart(
    poems_df,
    width=200,
    height=80
).mark_bar().encode(
  x=alt.X('n_verses:Q'),
  y='count()'
).facet(
    'book:N',
    columns=4
)

alt.FacetChart(...)

### Combinándolo todo: Interacción.

Para completar esta lección, vamos a ver cómo relacionar el gráfico facetado del ejemplo anterior con el de análisis de patrones rítmicos que creamos más arriba.

La idea es crear un gráfico que nos permita explorar *interactivamente* nuestro corpus, en un enfoque radicalmente diferente (y generalmente mucho más potente) al de las visualizaciones estáticas. Estaríamos adentrándonos en el mundo de la [análitica visual](https://en.wikipedia.org/wiki/Visual_analytics).

En este ejemplo vamos a implementar una técnica de interacción llamada Brushing+Linking (B+L). No te preocupes si el código te resulta un poco extraño todavía! Con este ejemplo, quiero mostrarte lo rápido que podemos construir este tipo de herramientas de análisis en Altair (y animarte a que aprendas Altair). Si te ha gustado este cuaderno, puedes continuar tu aprendizaje [aquí](https://github.com/uwdata/visualization-curriculum).

#### Brushing + Linking
La técnica del brushing and linking (B+L) es una técnica de visualización de datos interactiva que permite explorar y analizar patrones en diferentes variables de un conjunto de datos.

La técnica se basa en dos acciones principales:

"Brushing": Consiste en resaltar un subconjunto de datos de una visualización a través de la selección interactiva. Esto se puede hacer mediante el uso del mouse o del dedo en pantallas táctiles.

"Linking": Consiste en establecer una conexión entre dos o más visualizaciones, de manera que cuando se selecciona un subconjunto de datos en una visualización, los datos correspondientes se destacan automáticamente en las otras visualizaciones vinculadas.

Esta técnica permite al usuario explorar y analizar patrones en diferentes variables de un conjunto de datos y cómo interactúan entre sí. Por ejemplo, se puede utilizar para analizar la relación entre la edad y el ingreso en una población, o para explorar la relación entre la precipitación y la temperatura en diferentes regiones geográficas. La técnica del brushing and linking es una herramienta poderosa para descubrir patrones ocultos y relaciones en grandes conjuntos de datos de manera eficiente y efectiva.

### Aplicándolo todo a nuestro ejemplo
Con estas premisas, vamos a juntar las vistas de las secciones "Agregando de otra manera" y "Desagregando" en un único *dashboard* interactivo de exploración.



In [ ]:
#Creamos un tipo de selección de tipo brush que nos permita seleccionar el eje x.
brush = alt.selection_interval(encodings=['x'])

#Como hicimos antes, creamos un gráfico base en el que las barras van a mostrar la
# frecuencia absoluta de n_verses en un intervalo (bin)
base = alt.Chart(
    width=120,
    height=80
).mark_bar().encode(
  x=alt.X('n_verses:Q', bin=alt.Bin(maxbins=10)),
  y='count()'
)

#Creamos un gráfico de barras de color gris (lo que se muestra cuando no está seleccionado)
background = base.encode(
    color=alt.value('#ddd')
).add_selection(brush)

#Y ahora creamos un filtrado dinámico de los datos
#que se basa en la acción de seleccionar (brush)
highlight = base.transform_filter(brush)

#Por último, vamos a poner en capas las dos, y además generaremos un gráfico
#facetado por colección (book). Esta es la parte izquierda del gráfico final.
bars_multi = alt.layer(
    background,
    highlight,
    data=poems_df,
).facet(
    'book:N',
    columns=4
)

#Ahora vamos con la parte derecha, que muestra los patrones rítmicos.
#Es igual que el que creamos antes, con la diferencia de que ahora
#usamos un filtrado dinámico mediante transform_filter que depende de la
#selección del usuario en un momento dado
# (y que es la misma que la que afecta a la parte izquierda del gráfico).
heatmap = alt.Chart(verses_df).mark_rect().encode(
    x='x:O',
    # La propieadad labelOverlap detecta cuando hay demasiadas etiquetas en el eje y elimina
    # algunas para maximizar la legibilidad (Prueba a setearla a "False")
    y=alt.Y('y:O', axis=alt.Axis(labelOverlap=True)),
    color='sum_stress:Q'
).transform_filter(
    brush
  ).transform_aggregate(
    sum_stress='sum(is_stressed)',
    groupby=['x', 'y']
).properties(width=150, height=360)

(bars_multi | heatmap) #El operador | concatena gráficos.

alt.HConcatChart(...)

### Probando, probando 🎤
Si ejectutaste la celda anterior, verás que el resultado es un panel con dos vistas en la que el flujo de datos se controla de manera unidireccional de izquierda a derecha (interacciones en el panel izquierdo dan como resultado actualizaciones en el panel derecho).

**¡Prueba a arrastrar el ratón en cualquiera de las vistas de la izquierda para ver cómo funciona!** De esta manera podemos ver una agregación del ritmo de los poemas que caigan en el umbral de longitud definido mediante nuestra interacción con la visualización.

Como ves, Altair ofrece una manera muy directa de obtener este tipo de visualizaciones interactivas, que son súmamente útiles en el [análisis exploratorio de datos](https://es.wikipedia.org/wiki/An%C3%A1lisis_exploratorio_de_datos) (EDA por sus siglas en inglés).

####  Comentarios finales
Aunque en este ejemplo no hemos entrado a analizar en profundidad los resultados que nos ofrece la visualización a la que hemos llegado, este sería el proceso lógico a seguir en un "caso real." En la práctica obligatoria de la asignatura, se espera que puedas extraer dicho conocimiento de los datos, y que estas conclusiones a las que llegues puedan ser observadas en las visualizaciones que presentes. Es decir, como la práctica trata de crear un storytelling coherente (más sobre esto en el tema 3 de la asignatura, pero te recomendamos además leer el [paper original](http://vis.stanford.edu/files/2010-Narrative-InfoVis.pdf), es necesario que acompañes la narración de tu investigación (en texto) con visualizaciones (interactivas o no) que soporten tu versión de la historia.

También has de tener en cuena que habitualmente va a ser necesario un preprocesamiento (más o menos inteligente) de los datos para que esta extracción de conocimiento, y su posterior presentación al usuario, sea efectiva. En esta ocasión, los datos (en formato texto) fueron procesados con una biblioteca al uso para la escansión de versos poéticos, obteniendo diferentes metadatos de interés. Pero existen otros muchos métodos (que quizás hayas visto en otras asignaturas) que podrías usar con otros tipos de datos. ¡Te animamos encarecidamente a experimentar con los que más te llamen la atención!

Por último, recomendamos visitar [curso de Altair de la Universidad de Washington](https://uwdata.github.io/visualization-curriculum/altair_introduction.html) y la [la galería de ejemplos de Altair](https://altair-viz.github.io/gallery/), que seguramente te sean de ayuda para crear tus propias visualizaciones con esta biblioteca.

### Fin
Hemos llegado al final de esta lección. ¡Esperamos que te haya gustado este cuaderno interactivo y hayas podido aprender un poco sobre el uso de vega-altair!

Te recomendamos que, para practicar, modifiques y adaptes los ejemplos de este cuaderno para intentar responder muchas de las preguntas que han quedado en el aire, como por ejemplo:

1. ¿Cuál es la longitud media del verso por colección? ¿Podrías añadir otras marcas visuales para representar esta media en algunos de los ejemplos que hemos visto vistos?
2. ¿Es la longitud del verso una función de su posición en el poema?
3. ¿Se puede adaptar el ejemplo interactivo para que nos permita filtrar por longitud de verso? ¿Y por otra característica? ¿Y por varias a la vez?
4. ¿Cuáles son los tipos de rima y terminaciones de versos más comunes? ¿Cómo puedo representarlo visualmente?
5. Etc...

Si tienes dudas o te atascas, puedes contactar con nosotros a través de los foros de la asignatura.

¡Hasta pronto!
